# Access to jobs by public transport in Montevideo

This report examines the percentage of jobs that residents can reach within 30, 45, and 60 minutes by public transport and walking. It serves a baseline to identify gaps in job access geographically and for planning future public transit.

## Findings

Accessibility describes how the public transport system connects people with economic opportunities. This analysis measures the percentage of jobs reachable within a specified travel time for each zone in Montevideo. The measure gives more weight to region where more people live.

For the Wednesday 08:00 baseline, the population-weighted resident can reach **9.50%** of modeled jobs within 30 minutes, **23.82%** within 45 minutes, and **37.90%** within 60 minutes.

> **Notes:** These figures include zones without a destination reachable inside the default two-hour routing horizon as zero. Of the 2,698,002 residents in the denominator, 1,846,591 live in zones with at least one routed destination. Appendix E separates origins that could not connect to the OSM walking network, origins beyond the two-hour limit, and peripheral areas outside the practical GTFS and employment-model coverage.

In [1]:
import datetime
from pathlib import Path

import altair as alt
import attaviz
import folium
import contextily as cx
import geopandas as gpd
import pandas as pd
import r5py
from IPython.display import display

attaviz.enable()


def find_project_root(marker="pyproject.toml"):
    current = Path.cwd()
    for parent in [current, *current.parents]:
        if (parent / marker).exists():
            return parent
    raise FileNotFoundError(f"Could not find {marker}")


def simplify_for_web(frame, tolerance=30):
    """Simplify projected geometry before embedding an interactive map."""
    display_frame = frame.to_crs(LOCAL_CRS).copy()
    display_frame.geometry = display_frame.geometry.simplify(
        tolerance, preserve_topology=True
    )
    return display_frame.to_crs(WGS84_CRS)


PROJECT_ROOT = find_project_root()
DATA_PATH = PROJECT_ROOT / "data"
POPULATION_PATH = DATA_PATH / "population" / "poblacion-zonificacion.gpkg"
EMPLOYMENT_PATH = DATA_PATH / "URY_montevideo_employment_predictions_relative.gpkg"
OSM_PATH = DATA_PATH / "uruguay-260624.osm.pbf"
FEEDS = [
    DATA_PATH / "GTFS" / "google_transit.zip",
    DATA_PATH / "GTFS" / "gtfs_20260326.zip",
]
OUTPUT_PATH = DATA_PATH / "opportunities"
POPULATION_MATRIX_PATH = OUTPUT_PATH / "accessibility_wed_08.parquet"
GRID_MATRIX_PATH = OUTPUT_PATH / "accessibility_grid_wed_08.parquet"

TILES = cx.providers.Esri.WorldGrayCanvas
LOCAL_CRS = "EPSG:32721"
WGS84_CRS = "EPSG:4326"
DEPARTURE = datetime.datetime(2026, 3, 25, 8, 0)
THRESHOLDS = (30, 45, 60)
SCENARIOS = (
    "wed_07",
    "wed_08",
    "wed_09",
    "wed_10",
    "sat_07",
    "sat_08",
    "sat_09",
    "sat_10",
)

# The eight direct scenario matrices are generated by
# src/montevideobrt/generate_population_job_matrices.py. Routing is expensive,
# so this flag only controls regeneration of the detailed Wednesday 08:00
# matrix used by the headline sections below.
RUN_POPULATION_ROUTING = False

## Data sources

| Dataset | Details |
|---|---|
| Population zoning | Population totals and origin polygons |
| Employment grid | Distribution of jobs across destination cells |
| OpenStreetMap network | Walking and street network for routing |
| GTFS feeds | Public-transit routes and schedules |
| Wednesday 08:00 detailed matrix | Population-zone origins to employment-grid destinations |
| Wednesday and Saturday matrices | Comparison across departure times |

In [2]:
population_zones = (
    gpd.read_file(POPULATION_PATH)
    .rename(columns={"id_poligono": "zone_id", "poblacion": "population"})
    .to_crs(LOCAL_CRS)
)
employment_grid = gpd.read_file(EMPLOYMENT_PATH)
employment = (
    employment_grid.copy()
    .assign(
        geometry=lambda df: df.geometry.to_crs(LOCAL_CRS).centroid.to_crs(WGS84_CRS)
    )
    .rename(columns={"grid_id": "id"})
)
population_origins = population_zones.rename(columns={"zone_id": "id"}).assign(
    geometry=lambda df: df.geometry.centroid.to_crs(WGS84_CRS)
)

data_inventory = pd.DataFrame(
    {
        "dataset": ["Population", "Employment grid"],
        "records": [len(population_zones), len(employment_grid)],
        "crs": [population_zones.crs.to_string(), employment_grid.crs.to_string()],
        "geometry": [
            population_zones.geometry.geom_type.mode().iat[0],
            employment_grid.geometry.geom_type.mode().iat[0],
        ],
        "fields": [
            ", ".join(population_zones.columns.drop("geometry")),
            ", ".join(employment_grid.columns.drop("geometry")),
        ],
    }
)
data_inventory

,dataset,records,crs,geometry,fields
0,Population,556,EPSG:32721,Polygon,"zone_id, tipo_zona, population"
1,Employment grid,3808,EPSG:4326,MultiPolygon,"grid_id, pred_relative_employment"


## Where people and jobs are located

### Population

The population data represents 2,698,002 residents in 552 zones with reported population with four additional zones have missing population. Population extends beyond the central urban area, including 736,199 residents in zones classified as `Periferia`.

### Share of jobs

The employment layer shows the percentage of jobs across 3,808 grid cells. The cell values sum to 100%, which allows cell to be interpreted as share of all jobs represented in the layer. Therefore the measure does not represent the count of observed jobs.

In [3]:
population_zone_summary = (
    population_zones.assign(population_missing=population_zones["population"].isna())
    .groupby("tipo_zona", dropna=False)
    .agg(
        zone_count=("zone_id", "size"),
        population=("population", "sum"),
        missing_population=("population_missing", "sum"),
    )
    .reset_index()
)
print(
    f"Population denominator: {population_zones['population'].sum():,.0f} people across {population_zones['population'].notna().sum():,} zones"
)
display(population_zone_summary)

population_context_map = simplify_for_web(population_zones).explore(
    column="population",
    cmap="Blues",
    legend=True,
    scheme="Quantiles",
    k=5,
    tooltip=["zone_id", "tipo_zona", "population"],
    tiles=TILES,
    legend_kwds={"caption": "Population"},
    style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
    missing_kwds={"color": "lightgrey", "label": "Missing population"},
)
display(population_context_map)

employment_context_map = simplify_for_web(employment_grid, tolerance=20).explore(
    column="pred_relative_employment",
    cmap="Purples",
    legend=True,
    scheme="Quantiles",
    k=5,
    tooltip=["grid_id", "pred_relative_employment"],
    tiles=TILES,
    legend_kwds={"caption": "Share of modeled jobs (%)"},
    style_kwds={"weight": 0.2, "color": "#756bb1", "fillOpacity": 0.75},
)
employment_context_map

Population denominator: 2,698,002 people across 552 zones


,tipo_zona,zone_count,population,missing_population
0,Core,544,1961803.0,4
1,Periferia,12,736199.0,0


## How accessibility is measured

For each region, we determine which destination cells can be reached within 30, 45, or 60 minutes by walking and public transport. It then adds the job shares in those reachable cells.

The main baseline represents departures beginning at 08:00 on Wednesday 25 March 2026. Travel times are estimated across a 60-minute departure window, and the median (`p50`) travel time is used. Each region and employment cells are represented by their centroids for routing. Full routing-generation details are provided in Appendix B.

In [4]:
if RUN_POPULATION_ROUTING:
    network = r5py.TransportNetwork(OSM_PATH, FEEDS)
    ttm_population = r5py.TravelTimeMatrix(
        network,
        origins=population_origins,
        destinations=employment,
        departure=DEPARTURE,
        departure_time_window=datetime.timedelta(minutes=60),
        percentiles=[50],
        transport_modes=[r5py.TransportMode.TRANSIT, r5py.TransportMode.WALK],
        snap_to_network=1600,
        max_time=datetime.timedelta(hours=2),
        max_time_walking=datetime.timedelta(hours=2),
    )
    population_matrix = ttm_population.rename(columns={"travel_time": "p50"})[
        ["from_id", "to_id", "p50"]
    ]
    population_matrix.to_parquet(POPULATION_MATRIX_PATH, index=False)
elif not POPULATION_MATRIX_PATH.exists():
    raise FileNotFoundError(
        f"{POPULATION_MATRIX_PATH} is missing. Set RUN_POPULATION_ROUTING=True to create it."
    )

population_matrix = pd.read_parquet(POPULATION_MATRIX_PATH)
matrix_summary = pd.DataFrame(
    {
        "measure": [
            "origin-destination pairs",
            "origins",
            "destinations",
            "non-null p50 pairs",
        ],
        "value": [
            len(population_matrix),
            population_matrix["from_id"].nunique(),
            population_matrix["to_id"].nunique(),
            population_matrix["p50"].notna().sum(),
        ],
    }
)
matrix_summary

,measure,value
0,origin-destination pairs,2104165
1,origins,553
2,destinations,3805
3,non-null p50 pairs,1556749


### Accessibility calculation

For region *i*, job cell *j*, and travel-time threshold *t*:

$$
A_i(t)
=
\sum_j \left[
\mathrm{job\_share}_j
\times
\mathbf{1}\!\left(\mathrm{travel\_time}_{ij} \leq t\right)
\right]
$$

Where `job_share_j` is destination cell *j*'s percentage of jobs. The indicator function equals one when the destination is reachable within the threshold and zero otherwise. The population-weighted value is:

$$
A_{\mathrm{population}}(t)
=
\frac{\sum_i \left[\mathrm{population}_i \times A_i(t)\right]}
     {\sum_i \mathrm{population}_i}
$$

This value describes the percentage of jobs reachable by the population-weighted resident. Appendix C documents the full notation and treatment of missing values.

## Where results are available

Before interpreting the accessibility, we first assess the routing coverage. The interactive map below distinguishes three situations: `Valid route within 2 hours` means the origin has at least one non-null route; `No destination within 2 hours` means the origin is present in the matrix but has no reachable job destination within two hours, and `Origin missing from matrix` means no origin-destination rows were generated because the centroid could not be linked to the OSM walking network. Appendix E explains these cases.

In [5]:
report_pairs = population_matrix.merge(
    employment_grid[["grid_id", "pred_relative_employment"]],
    left_on="to_id",
    right_on="grid_id",
    how="left",
)
report_accessibility_by_zone = (
    report_pairs.assign(
        **{
            f"accessibility_{minutes}min": report_pairs["pred_relative_employment"]
            .fillna(0)
            .where(report_pairs["p50"] <= minutes, 0)
            for minutes in THRESHOLDS
        }
    )
    .groupby("from_id")[[f"accessibility_{minutes}min" for minutes in THRESHOLDS]]
    .sum()
    .rename_axis("zone_id")
    .reset_index()
)
report_region = population_zones[["zone_id", "population"]].merge(
    report_accessibility_by_zone, on="zone_id", how="left"
)
report_region_valid = report_region["population"].notna()
report_population_denominator = report_region.loc[
    report_region_valid, "population"
].sum()
report_results = pd.DataFrame(
    {
        "threshold_minutes": THRESHOLDS,
        "modeled_jobs_reachable_pct": [
            (
                report_region.loc[report_region_valid, "population"]
                * report_region.loc[
                    report_region_valid, f"accessibility_{minutes}min"
                ].fillna(0)
            ).sum()
            / report_population_denominator
            for minutes in THRESHOLDS
        ],
    }
)
report_results.round(2)

,threshold_minutes,modeled_jobs_reachable_pct
0,30,9.50
1,45,23.82
2,60,37.90


In [6]:
report_origin_routes = (
    population_matrix.groupby("from_id")["p50"]
    .agg(lambda values: values.notna().any())
    .rename("has_any_route")
)
report_coverage = population_zones[["zone_id", "tipo_zona", "population"]].merge(
    report_origin_routes, left_on="zone_id", right_index=True, how="left"
)
report_coverage["has_any_route"] = (
    report_coverage["has_any_route"].fillna(False).astype(bool)
)
report_coverage_valid = report_coverage["population"].notna()
report_missing_origin_ids = sorted(
    set(report_coverage.loc[report_coverage_valid, "zone_id"])
    - set(population_matrix["from_id"])
)
report_missing_origin_population = report_coverage.loc[
    report_coverage_valid & report_coverage["zone_id"].isin(report_missing_origin_ids),
    "population",
].sum()
report_coverage_summary = pd.DataFrame(
    {
        "metric": [
            "Population denominator",
            "Population with at least one non-null route",
            "Population without a non-null route",
            "Population in missing origin rows",
            "Periferia population",
            "Periferia population with a non-null route",
        ],
        "people": [
            report_coverage.loc[report_coverage_valid, "population"].sum(),
            report_coverage.loc[
                report_coverage_valid & report_coverage["has_any_route"], "population"
            ].sum(),
            report_coverage.loc[
                report_coverage_valid & ~report_coverage["has_any_route"], "population"
            ].sum(),
            report_missing_origin_population,
            report_coverage.loc[
                report_coverage_valid & report_coverage["tipo_zona"].eq("Periferia"),
                "population",
            ].sum(),
            report_coverage.loc[
                report_coverage_valid
                & report_coverage["tipo_zona"].eq("Periferia")
                & report_coverage["has_any_route"],
                "population",
            ].sum(),
        ],
    }
)
print("Missing origin IDs:", report_missing_origin_ids)
display(report_coverage_summary)

coverage_map = population_zones.merge(
    report_coverage[["zone_id", "has_any_route"]], on="zone_id", how="left"
)
coverage_map["coverage_status"] = "No destination within 2 hours"
coverage_map.loc[coverage_map["has_any_route"].fillna(False), "coverage_status"] = (
    "Valid route within 2 hours"
)
coverage_map.loc[
    coverage_map["zone_id"].isin(report_missing_origin_ids), "coverage_status"
] = "Origin missing from matrix"
coverage_explore = simplify_for_web(coverage_map).explore(
    column="coverage_status",
    categorical=True,
    cmap=["#fdae6b", "#de2d26", "#2b8cbe"],
    tooltip=["zone_id", "tipo_zona", "population", "coverage_status"],
    tiles=TILES,
    legend_kwds={"caption": "Routing status"},
    style_kwds={"weight": 0.4, "color": "white", "fillOpacity": 0.75},
)
coverage_explore

Missing origin IDs: [469, 476, 546]


,metric,people
0,Population denominator,2698002.0
1,Population with at least one non-null route,1846591.0
2,Population without a non-null route,851411.0
3,Population in missing origin rows,81582.0
4,Periferia population,736199.0
5,Periferia population with a non-null route,0.0


## How many jobs can residents reach?

For the Wednesday 08:00 baseline, the population-weighted resident can reach **9.50%** of modeled jobs within 30 minutes, **23.82%** within 45 minutes, and **37.90%** within 60 minutes.

> **Notes:** Only 1,846,591 of the 2,698,002 residents are in origins with at least one destination inside the two-hour routing horizon. The 12 `Periferia` zones contain 736,199 residents and receive zero in the detailed matrix. For most peripheral zones, this reflects a mismatch between the regional population extent and the much smaller GTFS and employment-model coverage; it should not be interpreted as proof of zero access to all real jobs.

The map below shows the percentage of jobs reachable within 45 minutes. Areas without valid routing are identified separately so they are not mistaken for areas with measured low accessibility.

In [7]:
accessibility_bar = (
    alt.Chart(report_results)
    .mark_bar(color=attaviz.SEQ_PURPLE[-2])
    .encode(
        x=alt.X(
            "threshold_minutes:O",
            title="Travel-time threshold (minutes)",
            sort=list(THRESHOLDS),
        ),
        y=alt.Y(
            "modeled_jobs_reachable_pct:Q",
            title="Modeled jobs reachable (%)",
            scale=alt.Scale(domain=[0, 45]),
        ),
        tooltip=[
            alt.Tooltip("threshold_minutes:O", title="Minutes"),
            alt.Tooltip(
                "modeled_jobs_reachable_pct:Q",
                title="Modeled jobs reachable",
                format=".2f",
            ),
        ],
    )
    .properties(title="Regional population-weighted access", width=560, height=320)
)
accessibility_labels = accessibility_bar.mark_text(
    align="center", baseline="bottom", dy=-6, color=attaviz.TEXT
).encode(text=alt.Text("modeled_jobs_reachable_pct:Q", format=".2f"))
display(
    attaviz.add_caption(
        accessibility_bar + accessibility_labels,
        "Note: Results include all zones with reported population; see the routing coverage map.",
    )
)

result_map = population_zones.merge(
    report_accessibility_by_zone, on="zone_id", how="left"
).merge(report_coverage[["zone_id", "has_any_route"]], on="zone_id", how="left")
result_map["modeled_jobs_reachable_45min_pct"] = result_map[
    "accessibility_45min"
].where(result_map["has_any_route"].fillna(False))
accessibility_explore = simplify_for_web(result_map).explore(
    column="modeled_jobs_reachable_45min_pct",
    cmap="YlOrRd",
    legend=True,
    tooltip=[
        "zone_id",
        "tipo_zona",
        "population",
        "modeled_jobs_reachable_45min_pct",
    ],
    tiles=TILES,
    legend_kwds={"caption": "Jobs reachable within 45 minutes (%)"},
    style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.75},
    missing_kwds={
        "color": "lightgrey",
        "label": "No destination within routing horizon",
    },
)
accessibility_explore

alt.VConcatChart(...)

## Does accessibility change by day and departure time?

All eight day-and-time scenarios now use direct population-zone to employment-grid matrices, so the comparison uses the same destination geography as the Wednesday 08:00 headline.

In [8]:
scenario_matrix_paths = {
    scenario: OUTPUT_PATH / f"accessibility_{scenario}.parquet"
    for scenario in SCENARIOS
}
missing_scenario_matrices = [
    scenario for scenario, path in scenario_matrix_paths.items() if not path.exists()
]
if missing_scenario_matrices:
    raise FileNotFoundError(
        "Missing direct population-to-employment matrices: "
        + ", ".join(missing_scenario_matrices)
    )

scenario_rows = []
for scenario, matrix_path in scenario_matrix_paths.items():
    scenario_matrix = pd.read_parquet(matrix_path)
    scenario_scores = (
        scenario_matrix.merge(
            employment_grid[["grid_id", "pred_relative_employment"]],
            left_on="to_id",
            right_on="grid_id",
            how="left",
        )
        .assign(
            **{
                f"accessibility_{minutes}min": lambda frame, minutes=minutes: (
                    frame["pred_relative_employment"]
                    .fillna(0)
                    .where(frame["p50"] <= minutes, 0)
                )
                for minutes in THRESHOLDS
            }
        )
        .groupby("from_id")[[f"accessibility_{minutes}min" for minutes in THRESHOLDS]]
        .sum()
        .rename_axis("zone_id")
        .reset_index()
    )
    scenario_region = population_zones[["zone_id", "population"]].merge(
        scenario_scores, on="zone_id", how="left"
    )
    route_status = (
        scenario_matrix.groupby("from_id")["p50"]
        .agg(lambda values: values.notna().any())
        .rename("has_job_route")
    )
    scenario_region = scenario_region.merge(
        route_status, left_on="zone_id", right_index=True, how="left"
    )
    scenario_region["has_job_route"] = (
        scenario_region["has_job_route"].fillna(False).astype(bool)
    )
    scenario_valid = scenario_region["population"].notna()
    scenario_rows.append(
        {
            "scenario": scenario,
            **{
                f"{minutes} min": (
                    scenario_region.loc[scenario_valid, "population"]
                    * scenario_region.loc[
                        scenario_valid, f"accessibility_{minutes}min"
                    ].fillna(0)
                ).sum()
                / report_population_denominator
                for minutes in THRESHOLDS
            },
            "population_with_routed_job_destination": scenario_region.loc[
                scenario_valid & scenario_region["has_job_route"], "population"
            ].sum(),
        }
    )

scenario_results = pd.DataFrame(scenario_rows)
scenario_results.round(2).rename(
    columns={f"{minutes} min": f"{minutes} min (%)" for minutes in THRESHOLDS}
)

,scenario,30 min (%),45 min (%),60 min (%),population_with_routed_job_destination
0,wed_07,9.71,24.15,38.18,1850555.0
1,wed_08,9.50,23.82,37.90,1846591.0
2,wed_09,9.66,23.87,37.35,1843818.0
3,wed_10,9.74,23.97,37.70,1851238.0
4,sat_07,9.41,23.76,37.13,1839241.0
5,sat_08,9.38,23.61,36.99,1850600.0
6,sat_09,9.40,23.53,36.78,1840329.0
7,sat_10,9.41,23.52,36.72,1839241.0


In [14]:
scenario_plot = scenario_results.copy()
scenario_plot["day_code"] = scenario_plot["scenario"].str.extract(
    "^(wed|sat)_", expand=False
)
scenario_plot["day"] = scenario_plot["day_code"].map(
    {"wed": "Wednesday", "sat": "Saturday"}
)
scenario_plot["departure_hour"] = (
    scenario_plot["scenario"].str.extract(r"_(\d+)$", expand=False).astype(int)
)
scenario_plot["departure_time"] = scenario_plot["departure_hour"].map(
    lambda hour: f"{hour:02d}:00"
)
day_order = ["Wednesday", "Saturday"]
threshold_order = [f"{minutes} min" for minutes in THRESHOLDS]
hour_order = [
    f"{hour:02d}:00" for hour in sorted(scenario_plot["departure_hour"].unique())
]
scenario_long = scenario_plot.melt(
    id_vars=["scenario", "day", "departure_time"],
    value_vars=[f"{minutes} min" for minutes in THRESHOLDS],
    var_name="threshold",
    value_name="modeled_jobs_reachable_pct",
)
scenario_chart = (
    alt.Chart(scenario_long)
    .mark_line(point=True)
    .encode(
        x=alt.X(
            "departure_time:N",
            title="Departure time",
            sort=hour_order,
        ),
        y=alt.Y(
            "modeled_jobs_reachable_pct:Q",
            title="Modeled jobs reachable (%)",
            scale=alt.Scale(zero=False),
        ),
        color=alt.Color(
            "day:N",
            title="Day",
            sort=day_order,
        ),
        column=alt.Column(
            "threshold:N",
            title="Travel-time threshold",
            sort=threshold_order,
        ),
        tooltip=[
            alt.Tooltip("day:N", title="Day"),
            alt.Tooltip("departure_time:N", title="Departure time"),
            alt.Tooltip("threshold:N", title="Threshold"),
            alt.Tooltip(
                "modeled_jobs_reachable_pct:Q",
                title="Modeled jobs reachable",
                format=".2f",
            ),
        ],
    )
    .properties(
        title="Population-weighted access by threshold, departure hour, and day",
        width=240,
        height=380,
    )
    .resolve_scale(x="shared")
)
attaviz.add_caption(
    scenario_chart,
    "Note: Every scenario routes population zones directly to the employment grid.",
)

alt.VConcatChart(...)

## Conclusions

The Wednesday 08:00 baseline indicates that the population-weighted resident can reach **23.82% of jobs within 45 minutes** by public transport and walking. The range across Wednesday and Saturday 45-minutes scenarios is approximately 0.6 percentage points.

The analysis also identifies a major scope mismatch. Nearly one-third of the population has no destination within the default two-hour routing horizon, including all 12 `Periferia` zones, and three origin centroids cannot be linked to the OSM walking network.

### Implications for the next phase

1. Extend the employment and routing coverage to the complete population extent.
2. Use this baseline to compare current conditions with proposed BRT scenarios.

# Appendix

## Appendix A. Data sources and preparation

| Input | File or source | Preparation |
|---|---|---|
| Population zones | `data/population/poblacion-zonificacion.gpkg` | `id_poligono` is renamed `zone_id`; `poblacion` is renamed `population`; geometry is projected to EPSG:32721 |
| Modeled employment | `data/URY_montevideo_employment_predictions_relative.gpkg` | `pred_relative_employment` provides destination job shares and sums to approximately 100% |
| Street network | `data/uruguay-260624.osm.pbf` | Supplies the walking and street network |
| Public transport | `data/GTFS/google_transit.zip` and `data/GTFS/gtfs_20260326.zip` | Supplies routes, stops, and schedules |
| Detailed travel-time matrix | `data/opportunities/accessibility_wed_08.parquet` | Connects population-zone origins to employment-grid destinations |
| Scenario matrices | `data/opportunities/accessibility_{scenario}.parquet` | Connect population-zone origins directly to employment-grid destinations for Wednesday and Saturday at 07:00–10:00 |

Population polygons are represented by centroids when used as routing origins, but their complete reported populations are retained as regional weights. Employment polygons are represented by centroids when used as routing destinations. Four population zones with missing population values are excluded from the denominator.

## Appendix B. Routing generation

The eight direct matrices are generated with `r5py`. The transport network combines OpenStreetMap with both GTFS feeds. Wednesday scenarios use 25 March 2026 and Saturday scenarios use 28 March 2026, with departures at 07:00, 08:00, 09:00, and 10:00. Each run samples departures across a 60-minute window, enables public transport and walking, snaps origins and employment-grid destinations to the network, and retains the median (`p50`) travel time.

The matrices are generated by `src/montevideobrt/generate_population_job_matrices.py`; the notebook reads the saved files for analysis. Routing 556 origins to 3,808 destinations is computationally expensive, so generation is an explicit command rather than part of the normal report run:

```bash
PYTHONPATH=src .venv/bin/python -m montevideobrt.generate_population_job_matrices --overwrite
```

Each matrix row identifies an origin, a destination, and the median travel time in minutes. A null travel time means the routing process did not return a valid connection for that pair.

## Appendix C. Why some origins have no travel time

The detailed matrix has three distinct routing outcomes. Of the 552 populated origins, 519 have at least one destination within R5's default two-hour trip limit, 30 are present but have no destination within that limit, and three are absent because their centroids could not be linked to the OSM walking network. Four additional origins with valid routes have missing population values and are excluded from this count and the regional denominator.

### 1. Origins that could not link to the street network

With `snap_to_network=True`, R5 searches for a walkable street connection within 1,600 metres. An explicit snap test reproduces the three missing IDs—469, 476, and 546—exactly. Together, they represent 81,582 residents. Large or irregular polygons can place a geometric centroid far from a walkable street even when people live closer to the network elsewhere in the polygon. A population-weighted point or a representative inhabited point would be more defensible for these zones.

### 2. Origins beyond the default routing horizon

Thirty populated origins are present in the matrix but have null travel times to every modeled-job destination. A controlled reroute changed only `max_time` and `max_time_walking`, from the two-hour default to six hours. All 19 affected `Core` zones and peripheral zone 548 then produced at least one route. This confirms that they were linked to the network but had no modeled-job destination inside the original two-hour limit. For the 30-, 45-, and 60-minute indicators, their accessibility remains zero under the model.

### 3. Peripheral zones not covered by the available data

The remaining ten peripheral zones still produced no route in the six-hour test. Their centroids are approximately 31–161 km from the nearest GTFS stop and 51–186 km from the nearest modeled-job cell. OSM covers these areas, but the transit feeds and employment surface are concentrated much closer to Montevideo. Their zero scores therefore describe the current input scope, not access to every real job or transport service in those territories.

The maps below overlay routing status, the employment layer, GTFS routes, GTFS stops, and the OSM streets near the three unsnappable centroids. Routes reconstructed from the GTFS feed without `shapes.txt` connect ordered stops and are therefore approximate linework.

In [10]:
from zipfile import ZipFile

import pyogrio
from shapely.geometry import LineString


def read_gtfs_geometry(feed_path):
    """Read stops and one representative path per route from a GTFS archive."""
    feed_label = feed_path.stem
    with ZipFile(feed_path) as archive:
        stops_frame = pd.read_csv(archive.open("stops.txt"), dtype={"stop_id": str})
        trips_frame = pd.read_csv(archive.open("trips.txt"), dtype=str)
        routes_frame = pd.read_csv(archive.open("routes.txt"), dtype=str)
        stops_geometry = gpd.GeoDataFrame(
            stops_frame.assign(feed=feed_label),
            geometry=gpd.points_from_xy(
                stops_frame["stop_lon"], stops_frame["stop_lat"]
            ),
            crs=WGS84_CRS,
        )

        route_records = []
        if "shapes.txt" in archive.namelist():
            shapes_frame = pd.read_csv(
                archive.open("shapes.txt"), dtype={"shape_id": str}
            )
            shapes_frame["shape_pt_sequence"] = pd.to_numeric(
                shapes_frame["shape_pt_sequence"]
            )
            representative_shapes = (
                trips_frame[["route_id", "shape_id"]]
                .dropna()
                .drop_duplicates("route_id")
                .merge(
                    routes_frame[["route_id", "route_short_name"]],
                    on="route_id",
                    how="left",
                )
            )
            route_points = shapes_frame.merge(representative_shapes, on="shape_id")
            for route_id, points in route_points.sort_values(
                "shape_pt_sequence"
            ).groupby("route_id"):
                if len(points) > 1:
                    route_records.append(
                        {
                            "feed": feed_label,
                            "route_id": route_id,
                            "route_name": points["route_short_name"].iat[0],
                            "geometry": LineString(
                                zip(points["shape_pt_lon"], points["shape_pt_lat"])
                            ),
                        }
                    )
        else:
            stop_times_frame = pd.read_csv(
                archive.open("stop_times.txt"),
                dtype={"trip_id": str, "stop_id": str},
                usecols=["trip_id", "stop_id", "stop_sequence"],
            )
            stop_times_frame["stop_sequence"] = pd.to_numeric(
                stop_times_frame["stop_sequence"]
            )
            representative_trips = trips_frame.drop_duplicates("route_id")[
                ["route_id", "trip_id"]
            ].merge(
                routes_frame[["route_id", "route_short_name"]],
                on="route_id",
                how="left",
            )
            route_points = (
                stop_times_frame.merge(representative_trips, on="trip_id")
                .merge(
                    stops_frame[["stop_id", "stop_lon", "stop_lat"]],
                    on="stop_id",
                )
                .sort_values("stop_sequence")
            )
            for route_id, points in route_points.groupby("route_id"):
                if len(points) > 1:
                    route_records.append(
                        {
                            "feed": feed_label,
                            "route_id": route_id,
                            "route_name": points["route_short_name"].iat[0],
                            "geometry": LineString(
                                zip(points["stop_lon"], points["stop_lat"])
                            ),
                        }
                    )

    route_geometry = gpd.GeoDataFrame(route_records, crs=WGS84_CRS)
    return stops_geometry, route_geometry


gtfs_parts = [read_gtfs_geometry(feed_path) for feed_path in FEEDS]
gtfs_stops = pd.concat([part[0] for part in gtfs_parts], ignore_index=True)
gtfs_routes = pd.concat([part[1] for part in gtfs_parts], ignore_index=True)
gtfs_routes = gpd.GeoDataFrame(gtfs_routes, geometry="geometry", crs=WGS84_CRS)
gtfs_routes = gtfs_routes.to_crs(LOCAL_CRS)
gtfs_routes.geometry = gtfs_routes.geometry.simplify(100)

matrix_origin_ids = set(population_matrix["from_id"])
routed_origin_ids = set(
    population_matrix.loc[population_matrix["p50"].notna(), "from_id"]
)
origin_diagnostics = population_zones[
    ["zone_id", "tipo_zona", "population", "geometry"]
].copy()
origin_diagnostics.geometry = origin_diagnostics.geometry.centroid
origin_diagnostics["routing_status"] = origin_diagnostics["zone_id"].map(
    lambda zone_id: (
        "Valid route within 2 hours"
        if zone_id in routed_origin_ids
        else (
            "No destination within 2 hours"
            if zone_id in matrix_origin_ids
            else "Origin missing from matrix"
        )
    )
)

osm_bbox = tuple(origin_diagnostics.to_crs(WGS84_CRS).total_bounds)
osm_roads = pyogrio.read_dataframe(
    OSM_PATH,
    layer="lines",
    bbox=osm_bbox,
    columns=["osm_id", "highway"],
)
osm_roads = osm_roads[osm_roads["highway"].notna()].to_crs(LOCAL_CRS)
gtfs_stops_local = gpd.GeoDataFrame(
    gtfs_stops, geometry="geometry", crs=WGS84_CRS
).to_crs(LOCAL_CRS)
employment_points = employment_grid.to_crs(LOCAL_CRS)[["grid_id", "geometry"]].copy()
employment_points.geometry = employment_points.geometry.centroid

for field, target in {
    "nearest_gtfs_stop_m": gtfs_stops_local,
    "nearest_osm_road_m": osm_roads,
    "nearest_modeled_job_cell_m": employment_points,
}.items():
    nearest = gpd.sjoin_nearest(
        origin_diagnostics,
        target[["geometry"]],
        how="left",
        distance_col=field,
    )
    origin_diagnostics[field] = nearest.groupby(level=0)[field].min()

diagnostic_summary = (
    origin_diagnostics[origin_diagnostics["population"].notna()]
    .groupby(["routing_status", "tipo_zona"], dropna=False)
    .agg(
        zones=("zone_id", "size"),
        population=("population", "sum"),
        median_distance_to_gtfs_stop_m=("nearest_gtfs_stop_m", "median"),
        median_distance_to_job_cell_m=("nearest_modeled_job_cell_m", "median"),
    )
    .reset_index()
)
display(diagnostic_summary.round(0))

service_map = simplify_for_web(coverage_map).explore(
    column="coverage_status",
    categorical=True,
    cmap=["#fdae6b", "#de2d26", "#2b8cbe"],
    tooltip=["zone_id", "tipo_zona", "population", "coverage_status"],
    tiles=TILES,
    name="Population-zone routing status",
    style_kwds={"weight": 0.35, "color": "white", "fillOpacity": 0.65},
)
simplify_for_web(employment_grid.dissolve(), tolerance=50).explore(
    m=service_map,
    color="#54278f",
    name="Modeled-employment footprint",
    style_kwds={"weight": 2, "fillOpacity": 0.03},
)
gtfs_routes.to_crs(WGS84_CRS).explore(
    m=service_map,
    color="#238b45",
    tooltip=["feed", "route_name"],
    name="Representative GTFS route paths",
    style_kwds={"weight": 1.5, "opacity": 0.55},
)
folium.LayerControl(collapsed=False).add_to(service_map)
display(service_map)

missing_origins = origin_diagnostics[
    origin_diagnostics["routing_status"].eq("Origin missing from matrix")
].copy()
missing_search_area = missing_origins.buffer(5000).union_all()
missing_snap_radius = missing_origins.set_geometry(missing_origins.buffer(1600))
osm_near_missing = gpd.clip(osm_roads, missing_search_area)
stops_near_missing = gpd.clip(gtfs_stops_local, missing_search_area)

linkage_map = osm_near_missing.to_crs(WGS84_CRS).explore(
    color="#737373",
    tiles=TILES,
    tooltip=["osm_id", "highway"],
    name="OSM road features within 5 km",
    style_kwds={"weight": 1.5, "opacity": 0.7},
)
missing_snap_radius.to_crs(WGS84_CRS).explore(
    m=linkage_map,
    color="#f16913",
    name="R5 1,600 m snap search radius",
    style_kwds={"weight": 2, "fillOpacity": 0.05},
)
missing_origins.to_crs(WGS84_CRS).explore(
    m=linkage_map,
    color="#cb181d",
    marker_type="circle_marker",
    marker_kwds={"radius": 6, "fill": True},
    tooltip=["zone_id", "tipo_zona", "population"],
    name="Unsnappable origin centroids",
)
if not stops_near_missing.empty:
    stops_near_missing.to_crs(WGS84_CRS).explore(
        m=linkage_map,
        color="#238b45",
        marker_type="circle_marker",
        marker_kwds={"radius": 3, "fill": True},
        tooltip=["feed", "stop_name"],
        name="GTFS stops within 5 km",
    )
folium.LayerControl(collapsed=False).add_to(linkage_map)
linkage_map

,routing_status,tipo_zona,zones,population,median_distance_to_gtfs_stop_m,median_distance_to_job_cell_m
0,No destination within 2 hours,Core,19,103385.0,1308.0,16704.0
1,No destination within 2 hours,Periferia,11,666444.0,55079.0,89246.0
2,Origin missing from matrix,Core,2,11827.0,4640.0,16174.0
3,Origin missing from matrix,Periferia,1,69755.0,47788.0,99269.0
4,Valid route within 2 hours,Core,519,1846591.0,144.0,191.0


## Appendix D. Exploratory grid-based population analysis

The following analysis uses the employment grid as an exploratory origin geography. Population is allocated uniformly by area wherever a population polygon overlaps a grid cell. The raw allocation leaves population outside the grid unassigned; the alternative allocation renormalizes population within the covered portion of each zone.

This analysis is excluded from the main findings because the available population data do not measure population at grid-cell level and because the grid covers only part of the population extent.

In [11]:
grid_matrix = pd.read_parquet(GRID_MATRIX_PATH)
grid_scores = (
    grid_matrix.merge(
        employment_grid[["grid_id", "pred_relative_employment"]],
        left_on="to_id",
        right_on="grid_id",
        how="left",
    )
    .assign(
        accessibility_45min=lambda frame: (
            frame["pred_relative_employment"].fillna(0).where(frame["p50"] <= 45, 0)
        )
    )
    .groupby("from_id")["accessibility_45min"]
    .sum()
    .rename_axis("grid_id")
    .reset_index()
)
hex_source = population_zones[["zone_id", "population", "geometry"]].copy()
hex_source["zone_area_m2"] = hex_source.geometry.area
hex_intersections = gpd.overlay(
    hex_source,
    employment_grid[["grid_id", "geometry"]].to_crs(LOCAL_CRS),
    how="intersection",
    keep_geom_type=False,
)
hex_intersections["intersection_area_m2"] = hex_intersections.geometry.area
hex_intersections["covered_area_m2"] = hex_intersections.groupby("zone_id")[
    "intersection_area_m2"
].transform("sum")
hex_intersections["population_area_weighted"] = (
    hex_intersections["population"]
    * hex_intersections["intersection_area_m2"]
    / hex_intersections["zone_area_m2"]
)
hex_intersections["population_area_weighted_renormalized"] = (
    hex_intersections["population"]
    * hex_intersections["intersection_area_m2"]
    / hex_intersections["covered_area_m2"]
)
hex_population = hex_intersections.groupby("grid_id", as_index=False)[
    ["population_area_weighted", "population_area_weighted_renormalized"]
].sum()
hex_scores = (
    employment_grid[["grid_id", "geometry"]]
    .merge(grid_scores, on="grid_id", how="left")
    .merge(hex_population, on="grid_id", how="left")
)
for field in [
    "accessibility_45min",
    "population_area_weighted",
    "population_area_weighted_renormalized",
]:
    hex_scores[field] = hex_scores[field].fillna(0)
hex_summary = pd.DataFrame(
    {
        "measure": [
            "Hex cells",
            "Population assigned (raw area allocation)",
            "Population assigned (renormalized)",
            "Modeled jobs reachable, population weighted (raw, %)",
            "Modeled jobs reachable, population weighted (renormalized, %)",
        ],
        "value": [
            len(hex_scores),
            hex_scores["population_area_weighted"].sum(),
            hex_scores["population_area_weighted_renormalized"].sum(),
            (
                hex_scores["population_area_weighted"]
                * hex_scores["accessibility_45min"]
            ).sum()
            / hex_scores["population_area_weighted"].sum(),
            (
                hex_scores["population_area_weighted_renormalized"]
                * hex_scores["accessibility_45min"]
            ).sum()
            / hex_scores["population_area_weighted_renormalized"].sum(),
        ],
    }
)
hex_summary.round(2)

,measure,value
0,Hex cells,3808.00
1,Population assigned (raw area allocation),1693050.78
2,Population assigned (renormalized),1793693.00
3,"Modeled jobs reachable, population weighted (r...",38.51
4,"Modeled jobs reachable, population weighted (r...",36.56


In [12]:
hex_scores.to_crs(WGS84_CRS).explore(
    column="accessibility_45min",
    cmap="YlOrRd",
    legend=True,
    tooltip=["grid_id", "population_area_weighted", "accessibility_45min"],
    tiles=TILES,
)

The raw grid-based mean is **38.51% of modeled jobs** at 45 minutes, while the renormalized sensitivity is **36.56%**. Only about 1.69 million of the 2.70 million residents are assigned to grid cells under the raw area allocation. The difference from the preferred regional result is therefore expected: this diagnostic uses a different origin geography and a partial population denominator.

The map should remain an exploratory diagnostic until a higher-resolution population surface or another defensible grid-level population allocation is available.

### Appendix F interpretation

The grid-based estimates must not be compared directly with the preferred 23.82% regional estimate as if they were alternative measurements of the same population. They use different origin geographies, different population-allocation assumptions, and different effective denominators. Their purpose is to reveal spatial patterns and test assumptions—not to provide a second headline indicator.